# Generate motions using custom text prompts

First, run the following cell until (Modify here).

In [ ]:
%load_ext autoreload
%autoreload 2

import os
from os.path import join as pjoin

import torch
import torch.nn.functional as F

from models.klvae.autoencoder import AutoencoderKL as KLVAE
from models.mask_transformer.latent_transformer import MaskLatentTransformer
from models.length_est import LengthEstimator


from tqdm import tqdm

from visualization.remove_fs import *

# from utils.plot_script import plot_3d_motion
from visualization.plot_3d_global import plot_3d_motion

from utils.fixseed import fixseed
from torch.distributions.categorical import Categorical

from utils.motion_process import recover_from_ric

from options.train_option import add_train_mode_args, load_config_file_and_parse
from utils.diffusion import create_model_and_diffusion, create_gaussian_diffusion_ddim

import numpy as np
import sys
from argparse import ArgumentParser
import pickle
import imageio

import ipywidgets as widgets
from torch_ema import ExponentialMovingAverage
import itertools

from utils.demo_util import filtering, convert_npy_to_smplx_npz, sanitize_filename, Joint2BVHConvertor

clip_version = 'ViT-B/32'

In [ ]:
def load_kl_model(opt):
    with open(pjoin(opt.checkpoints_dir, opt.dataset_name, opt.kl_name, 'args_for_pretrained_klvae.pkl'), 'rb') as f:
        args = pickle.load(f)
    # args.dataset_name = args.dataname
    kl_model = KLVAE(args, ## use args to define different parameters in different quantizers
                     args.output_emb_width,
                     args.down_t,
                     args.stride_t,
                     args.width,
                     args.depth,
                     args.dilation_growth_rate)
    args.klvae_pth=pjoin(opt.checkpoints_dir, opt.dataset_name, opt.kl_name, 'net_last.pth')
    ckpt = torch.load(args.klvae_pth, map_location='cpu')
    kl_model.load_state_dict(ckpt['net'], strict=True)
    print(f'Loading KL Model {opt.kl_name}')
    return kl_model, args


def load_models(model_opt, which_model):
    cond_mode = 'text' if not model_opt.unconstrained else 'uncond'
    diff_model, diffusion = create_model_and_diffusion(model_opt)

    latent_transformer = MaskLatentTransformer(code_dim=model_opt.code_dim,
                                               cond_mode=cond_mode,
                                               latent_dim=model_opt.latent_dim,
                                               ff_size=model_opt.ff_size,
                                               num_layers=model_opt.n_layers,
                                               num_heads=model_opt.n_heads,
                                               dropout=model_opt.dropout,
                                               clip_dim=512,
                                               cond_drop_prob=model_opt.cond_drop_prob,
                                               opt=model_opt,
                                               clip_version=clip_version,
                                               use_ema=model_opt.use_ema)
    ckpt = torch.load(pjoin(model_opt.checkpoints_dir, model_opt.dataset_name, model_opt.name, 'model', which_model),
                      map_location=opt.device)
    model_key = 't2m_transformer' if 't2m_transformer' in ckpt else 'trans'

    if 'ema' in which_model:
        print("[Info] Using EMA")
        ema = ExponentialMovingAverage(itertools.chain(latent_transformer.parameters(), diff_model.parameters()), decay=opt.ema_decay)
        ema.load_state_dict(ckpt)
        ema.copy_to(itertools.chain(latent_transformer.parameters(), diff_model.parameters()))
        print("Loading EMA weights")
    else:
        missing_keys, unexpected_keys = latent_transformer.load_state_dict(ckpt[model_key], strict=False)
        assert len(unexpected_keys) == 0
        assert all([k.startswith('clip_model.') for k in missing_keys])
        print(f'Loading Mask Transformer {model_opt.name} from epoch {ckpt["ep"]}!')
        diff_model.load_state_dict(ckpt['diff_model'])
        print(f'Loading Diffusion {model_opt.name} from epoch {ckpt["ep"]}!')
        print(f'[Warning] Missing keys: ', missing_keys)

    return latent_transformer, diff_model, diffusion

def load_len_estimator(opt):
    model = LengthEstimator(512, 50)
    ckpt = torch.load(pjoin(opt.checkpoints_dir, opt.dataset_name, 'length_estimator', 'model', 'finest.tar'),
                          map_location=opt.device)
    model.load_state_dict(ckpt['estimator'])
    print(f'Loading Length Estimator from epoch {ckpt["epoch"]}!')
    return model



In [ ]:
sys.argv = ['notebook', '--name', 'Trans-B_EMA_klv0-stable_masked-only_diff1000', '--config', 'configs/t2m.yaml', '--use_ema', 'true', '--diffusion_steps', '1000', '--loss_strategy', 'masked', '--ddim_steps', '100', '--trans_infer_timesteps', '9', '--guidance_param', '3']

In [ ]:
parser = ArgumentParser()
parser = add_train_mode_args(parser)
opt = load_config_file_and_parse(parser)
fixseed(opt.seed)

opt.device = torch.device("cpu" if opt.device == -1 else "cuda:" + str(opt.device))
torch.autograd.set_detect_anomaly(True)

# out_dir = pjoin(opt.check)
root_dir = pjoin(opt.checkpoints_dir, opt.dataset_name, opt.name)
model_dir = pjoin(root_dir, 'model')

In [ ]:
encdec_model, encdec_opt = load_kl_model(opt)
encdec_model=encdec_model.to(opt.device)

In [ ]:
file = 'latest_ema.tar'


latent_transformer, diff_model, diffusion = load_models(opt, file)


latent_transformer.to(opt.device)
encdec_model.to(opt.device)
diff_model.to(opt.device)

diff_model.eval()
latent_transformer.eval()
encdec_model.eval()


if opt.ddim_steps != -1:
    print(f'Using DDIM with {opt.ddim_steps} steps')
    diffusion = create_gaussian_diffusion_ddim(opt, opt.ddim_steps)

In [ ]:
length_estimator = load_len_estimator(opt)

In [ ]:
latent_transformer.eval()
encdec_model.eval()
length_estimator.eval()

In [ ]:
latent_transformer.to(opt.device)
encdec_model.to(opt.device)
length_estimator.to(opt.device)

In [ ]:
opt.nb_joints = 21 if opt.dataset_name == 'kit' else 22

mean = np.load(pjoin(opt.meta_dir, 'mean.npy'))
std = np.load(pjoin(opt.meta_dir, 'std.npy'))
def inv_transform(data):
    return data * std + mean

## Modify Here
prompt: write the text of motion you want to generate

- length：you can set the length of the motion here, length*4 will be the final frames of motion if length!=0, or it will be estimate by the text.
- opt.repeat_times: the number of motions that generated by one prompt.
- motion_name: set the motion name with this, if it is none, it will be the text prompt.
- result_dir: the npy/bvh/mp4 will be saved here.

In [ ]:
# modify prompt and parameter here
prompt = "a person is kick boxing and holding his arms in front of his chest."
length = 0 # Specify motion length // 4 here. 49 indicates 196 frames.
opt.repeat_times = 10 # generate motions number
opt.time_steps = 7
opt.cond_scale = 3
motion_name = "" # set your motion name here
if not motion_name:
    motion_name = sanitize_filename(prompt)
print(motion_name)
result_dir = pjoin("./generation/test_gif", motion_name)
os.makedirs(result_dir, exist_ok=True)

In [ ]:
# Now enable estimation on length
import warnings
warnings.filterwarnings("ignore", category=UserWarning, module="matplotlib.animation")
if length == 0:
    print("Since no motion length are specified, we will use estimated motion lengthes!!")
    text_embedding = latent_transformer.encode_text(prompt)
    pred_dis = length_estimator(text_embedding)
    probs = F.softmax(pred_dis, dim=-1)  # (b, ntoken)
    token_lens = Categorical(probs).sample()  # (b, seqlen)
    token_lens = token_lens[:1]
else:
    token_lens = torch.tensor([length], device=opt.device, dtype=torch.long)

m_length = token_lens * 4
captions = prompt

print(m_length)
joints_dir = result_dir

img_widgets = []
for r in range(opt.repeat_times):
    print("-->Repeat %d"%r)
    caption = prompt
    if r == 0:
        print("token_lens :", token_lens)
        print("filename: ", motion_name)
        
    with torch.no_grad():
        noise_schedule = None
        pred_latent, gen_steps = latent_transformer.generate([caption], token_lens, opt.time_steps,
                                                                 opt.cond_scale, diffusion=diffusion, diff_model=diff_model,
                                                                 output_inference_step=True, noise_schedule=noise_schedule)
        
        pred_motions = encdec_model.decode(pred_latent)
        pred_motions = pred_motions.detach().cpu().numpy()
        data = inv_transform(pred_motions)

        

        data = data[:m_length]
        joint = recover_from_ric(torch.from_numpy(data).float(), 22).numpy()
        assert joint.shape[0] == 1
        joint = joint[0]
        joint = filtering(joint, m_length, window_size=15, poly_order=3)
    
        # save as npy
        if r == 0:
            print("Saving npy to ", pjoin(joints_dir, "%s_repeat%d_len%d"%(motion_name, r, m_length)))
            print("[Debug] Shape of joint: ", joint.shape)
        np.save(pjoin(joints_dir, "%s_repeat%d_len%d.npy"%(motion_name, r, m_length)), joint)

        converter = Joint2BVHConvertor()
        bvh_path = pjoin(joints_dir, "%s_repeat%d_len%d.bvh"%(motion_name, r, m_length))
        anim, glb = converter.convert(joint, bvh_path, foot_ik=True)
        img = plot_3d_motion([joint, None, None])
        gif_path = os.path.join(joints_dir, "%s_repeat%d_len%d.gif"%(motion_name, r, m_length))
        imageio.mimsave(gif_path, img.cpu().numpy(), fps=20, loop=0)
        with open(gif_path, "rb") as f:
            gif_play = f.read()
            img_widget = widgets.Image(
                value=gif_play,
                format='gif',
                width=500,
                height=500)
            img_widgets.append(img_widget)

hbox = widgets.HBox(img_widgets)
display(hbox)

print("DONE!")

### **Optional: convert npy(T, 22, 3) to smplx npz**
Prerequisite: Please refer to [MDM download_smpl_files] (https://github.com/GuyTevet/motion-diffusion-model/blob/main/prepare/download_smpl_files.sh) to download smplx files to `body_models`.

It will take a long time, if you really need this, using the following code.

In [ ]:
# convert to smplx npz
npy_files = [f for f in os.listdir(joints_dir) if f.endswith('.npy')]
for f in tqdm(npy_files):
    convert_npy_to_smplx_npz(pjoin(joints_dir, f), joints_dir, device=opt.device.index if opt.device != torch.device('cpu') else 0, cuda=opt.device != torch.device('cpu'))
